# Data Ingestion/Preprocessing
Utilize Last Observation Carried Forward (LOCF) for tracking spread where last known price of an asset remains valid until a new quote overwrites it.


In [5]:
import pandas as pd
import numpy as np
from preprocessing import reconstruct_continuous_book

# =====================================================================
# 1. DATA INGESTION & SYNCHRONIZATION
# =====================================================================
df_perp = reconstruct_continuous_book("BTCPERP")
df_spot = reconstruct_continuous_book("BTCUSDT")

df_perp = df_perp.rename(columns={'best_bid': 'perp_bid', 'best_ask': 'perp_ask'})
df_spot = df_spot.rename(columns={'best_bid': 'spot_bid', 'best_ask': 'spot_ask'})

# FIX: Explicitly create perp_time and spot_time so they are not swallowed
# by the merge_asof operation. We need these for the feed_latency_ms calculation!
df_perp['perp_time'] = df_perp['time']
df_spot['spot_time'] = df_spot['time']

print("Aligning asynchronous data streams...")
df_arb = pd.merge_asof(
    df_perp[['time', 'perp_time', 'perp_bid', 'perp_ask']], 
    df_spot[['time', 'spot_time', 'spot_bid', 'spot_ask']], 
    on='time', 
    direction='backward'
)
df_arb = df_arb.dropna().copy()

[BTCPERP] Fetching raw LOB events from database...
[BTCPERP] Reconstructing book from 565599 events...
[BTCPERP] Successfully generated 107316 continuous BBO states.

[BTCUSDT] Fetching raw LOB events from database...
[BTCUSDT] Reconstructing book from 1033374 events...
[BTCUSDT] Successfully generated 136344 continuous BBO states.

Aligning asynchronous data streams...


# QR1: Arbitraging Threshold, When is Slippage Too Expensive? Exploring Arbitrage Decay.
Solve this by calculating zscore levels relative to price level then making this to a histogram curve to investigate and isolate spread threshold.

In [ ]:
import numpy as np
import pandas as pd
from preprocessing import reconstruct_continuous_book

# =====================================================================
# 1. DATA INGESTION & SIGNAL CONSTRUCTION
#    (unchanged from the existing pipeline — kept here for completeness)
# =====================================================================


def prepare_signals(df, window=1000, max_staleness_ms=100, min_vol_usd=1.0):
    df = df.copy()
    df['feed_latency_ms'] = (df['perp_time'] - df['spot_time']).abs().dt.total_seconds() * 1000.0
    df['is_stale'] = df['feed_latency_ms'] > max_staleness_ms

    df['perp_mid'] = (df['perp_bid'] + df['perp_ask']) / 2.0
    df['spot_mid'] = (df['spot_bid'] + df['spot_ask']) / 2.0
    df['mid_spread'] = df['perp_mid'] - df['spot_mid']

    df['exec_short_spread'] = df['perp_bid'] - df['spot_ask']   # sell perp / buy spot
    df['exec_long_spread'] = df['perp_ask'] - df['spot_bid']    # buy perp / sell spot

    rolling_med = df['mid_spread'].rolling(window=window, min_periods=window // 2).median()
    rolling_mad = (df['mid_spread'] - rolling_med).abs().rolling(window=window, min_periods=window // 2).median()
    scale = np.maximum(rolling_mad * 1.4826, min_vol_usd)
    df['z_score'] = (df['mid_spread'] - rolling_med) / scale
    df.loc[df['is_stale'], 'z_score'] = 0.0
    return df


# =====================================================================
# 2. ECONOMIC TTR ENGINE
#    TTR is redefined as: time from entry until the position could be
#    closed at a net profit (crossing-spread PnL minus fees), NOT time
#    until the z-score statistically reverts to 0. Entry_latency is placed
#    to show the profitability of the strategy, how fast the algorithm
#    must run.
#
#    Two failure modes are handled explicitly instead of being silently
#    dropped:
#      - breakdown: |z| keeps growing past a threshold -> the spread
#        relationship itself may have broken (non-arbitrageable regime).
#      - timeout: max_horizon_ms elapses with no profitable exit.
#    Both are recorded as *censored* observations (event=False), not
#    discarded, so downstream stats aren't survivorship-biased toward
#    only the trades that happened to work.
# =====================================================================
def run_economic_backtest(
    df,
    entry_z=1.0,
    entry_latency_ms=0,
    fee_hurdle_usd=20.0,
    max_horizon_ms=5000,
    breakdown_z=6.0,
):
    timestamps = df['time'].values
    z = df['z_score'].values
    exec_short = df['exec_short_spread'].values   # sell perp / buy spot
    exec_long = df['exec_long_spread'].values      # buy perp / sell spot
    n = len(df)

    events = []
    i = 0
    while i < n:
        if abs(z[i]) < entry_z:
            i += 1
            continue

        # --- entry (threshold crossing, not the unknown future extremum) ---
        signal_time = timestamps[i]
        excursion_type = 1 if z[i] >= entry_z else -1   # 1: short perp/long spot

        fill_idx = np.searchsorted(timestamps, signal_time + np.timedelta64(entry_latency_ms, 'ms'))
        fill_idx = min(fill_idx, n - 1)
        entry_fill = exec_short[fill_idx] if excursion_type == 1 else exec_long[fill_idx]

        entry_z_val = z[i]
        peak_z = abs(z[i])
        j = i + 1
        outcome = None  # ('profit', j) | ('breakdown', j) | ('timeout', j)

        while j < n:
            elapsed_ms = (timestamps[j] - signal_time) / np.timedelta64(1, 'ms')
            if abs(z[j]) > peak_z:
                peak_z = abs(z[j])

            # Mark-to-market net PnL if closed right now, using the
            # actually-crossable bid/ask spread, not mid.
            if excursion_type == 1:
                exit_pay = exec_long[j]           # buy back perp / sell spot
                net_pnl = entry_fill - exit_pay - fee_hurdle_usd
            else:
                exit_pay = exec_short[j]
                net_pnl = exit_pay - entry_fill - fee_hurdle_usd

            if net_pnl > 0:
                outcome = ('profit', j, net_pnl)
                break
            if abs(z[j]) > breakdown_z:
                outcome = ('breakdown', j, net_pnl)
                break
            if elapsed_ms > max_horizon_ms:
                outcome = ('timeout', j, net_pnl)
                break
            j += 1

        if outcome is None:
            # Data ran out before any resolution — still censor it,
            # do not drop it silently.
            j = n - 1
            net_pnl = (entry_fill - exec_long[j] - fee_hurdle_usd) if excursion_type == 1 \
                else (exec_short[j] - entry_fill - fee_hurdle_usd)
            outcome = ('timeout', j, net_pnl)

        reason, exit_idx, net_pnl = outcome
        ttr_ms = (timestamps[exit_idx] - signal_time) / np.timedelta64(1, 'ms')

        events.append({
            'entry_z': entry_z_val,
            'peak_z_score': peak_z,
            'excursion_type': excursion_type,
            'ttr_ms': ttr_ms,
            'net_pnl_usd': net_pnl,
            'exit_reason': reason,
            'event_observed': reason == 'profit',   # False => censored
        })

        i = exit_idx + 1

    return pd.DataFrame(events)


# =====================================================================
# 3. KAPLAN-MEIER ESTIMATOR
#    P(profitable exit achieved by time t), correctly accounting for
#    censored trades (breakdown / timeout) instead of just averaging
#    over the trades that happened to resolve.
# =====================================================================
def kaplan_meier(durations, event_observed):
    d = pd.DataFrame({'t': durations, 'event': event_observed}).sort_values('t')
    n_total = len(d)
    survival = 1.0
    rows = [(0.0, 1.0)]
    for t in sorted(d.loc[d['event'], 't'].unique()):
        at_risk = (d['t'] >= t).sum()
        died = ((d['t'] == t) & d['event']).sum()
        if at_risk > 0:
            survival *= (1 - died / at_risk)
        rows.append((t, survival))
    km = pd.DataFrame(rows, columns=['t_ms', 'survival_prob'])
    km['p_profitable_by_t'] = 1 - km['survival_prob']
    return km


# =====================================================================
# 4. REPORTING
# =====================================================================
def generate_economic_report(df_events):
    if len(df_events) == 0:
        print("No excursions identified.")
        return

    bins = [1.0, 2.0, 3.0, 4.0, np.inf]
    labels = ['1.0 - 2.0', '2.0 - 3.0', '3.0 - 4.0', '4.0+']
    df_events = df_events.copy()
    df_events['z_tier'] = pd.cut(df_events['peak_z_score'], bins=bins, labels=labels, right=False)

    print("\n" + "=" * 70)
    print("=== EVENT OUTCOME BREAKDOWN BY Z-TIER ===")
    print("=" * 70)
    outcome_tbl = df_events.groupby(['z_tier', 'exit_reason'], observed=False).size().unstack(fill_value=0)
    print(outcome_tbl.to_string())

    print("\n" + "=" * 70)
    print("=== TIME-TO-PROFITABLE-EXIT (ms) — OBSERVED EVENTS ONLY ===")
    print("=" * 70)
    profitable = df_events[df_events['event_observed']]
    ttr_stats = profitable.groupby('z_tier', observed=False)['ttr_ms'].agg(
        Count='count', p25=lambda x: np.percentile(x, 25) if len(x) else np.nan,
        Median='median', p75=lambda x: np.percentile(x, 75) if len(x) else np.nan,
    ).reset_index()
    print(ttr_stats.to_string(index=False))
    print("\nNote: this table alone survivorship-biases toward trades that")
    print("worked. Use the Kaplan-Meier curve below for the full picture,")
    print("including tiers dominated by breakdown/timeout censoring.")

    print("\n" + "=" * 70)
    print("=== KAPLAN-MEIER: P(profitable exit by time t), BY Z-TIER ===")
    print("=" * 70)
    for tier in labels:
        sub = df_events[df_events['z_tier'] == tier]
        if len(sub) == 0:
            continue
        km = kaplan_meier(sub['ttr_ms'].values, sub['event_observed'].values)
        censor_rate = 1 - sub['event_observed'].mean()
        print(f"\nz_tier {tier}  (n={len(sub)}, censored={censor_rate:.1%})")
        print(km.iloc[::max(1, len(km) // 8)].to_string(index=False))


# =====================================================================
# 5. EXECUTION
# =====================================================================
if __name__ == "__main__":
    df_signals = prepare_signals(df_arb, window=1000, max_staleness_ms=100, min_vol_usd=1.0)

    df_events = run_economic_backtest(
        df_signals,
        entry_z=1.0,
        entry_latency_ms=100,
        fee_hurdle_usd=2.0,
        max_horizon_ms=5000,   # tune to your actual holding tolerance
        breakdown_z=6.0,       # tune to how far you'll let z run before distrust
    )

    generate_economic_report(df_events)


=== EVENT OUTCOME BREAKDOWN BY Z-TIER ===
exit_reason  breakdown  profit  timeout
z_tier                                 
1.0 - 2.0            0    7496       50
2.0 - 3.0            0    2519       30
3.0 - 4.0            0     847       18
4.0+               475    1461       46

=== TIME-TO-PROFITABLE-EXIT (ms) — OBSERVED EVENTS ONLY ===
   z_tier  Count  p25  Median  p75
1.0 - 2.0   7496 19.0    20.0 25.0
2.0 - 3.0   2519 20.0    20.0 21.0
3.0 - 4.0    847 19.0    20.0 21.0
     4.0+   1461 19.0    20.0 34.0

Note: this table alone survivorship-biases toward trades that
worked. Use the Kaplan-Meier curve below for the full picture,
including tiers dominated by breakdown/timeout censoring.

=== KAPLAN-MEIER: P(profitable exit by time t), BY Z-TIER ===

z_tier 1.0 - 2.0  (n=7546, censored=0.7%)
  t_ms  survival_prob  p_profitable_by_t
   0.0       1.000000           0.000000
  41.0       0.159157           0.840843
  84.0       0.081103           0.918897
 125.0       0.048105      

In [17]:
import numpy as np
import pandas as pd
from plotly.subplots import make_subplots
import plotly.graph_objects as go

# ---------------------------------------------------------
# Make sure the signal columns actually exist before plotting.
# df_arb only has raw book data at this point — prepare_signals()
# is what creates 'mid_spread' and 'z_score'.
# ---------------------------------------------------------
df_arb['time'] = pd.to_datetime(df_arb['time'])
df_plot = prepare_signals(df_arb, window=1000, max_staleness_ms=100, min_vol_usd=1.0)

# Reset index to guarantee sequential 0..N integer positioning (removes time gaps)
df_plot = df_plot.reset_index(drop=True)
x_axis = df_plot.index

# Create a 2-panel interactive subplot stacked vertically sharing x-axis
fig = make_subplots(
    rows=2, cols=1,
    shared_xaxes=True,
    vertical_spacing=0.08,
    subplot_titles=("Arbitrage Basis Spread ($)", "Z-Score & Trigger Thresholds")
)

# ---------------------------------------------------------
# TOP PANEL: Spot / Perp Basis Spread ($)
# ---------------------------------------------------------
fig.add_trace(
    go.Scatter(
        x=x_axis,
        y=df_plot['mid_spread'],          # <-- was 'spread'
        mode='lines',
        name='Spread ($)',
        line=dict(color='#1f77b4', width=1.2),
        customdata=df_plot['time'],
        hovertemplate='<b>Time</b>: %{customdata|%Y-%m-%d %H:%M:%S}<br><b>Spread</b>: $%{y:.2f}<extra></extra>'
    ),
    row=1, col=1
)

# ---------------------------------------------------------
# BOTTOM PANEL: Z-Score with Trigger Thresholds
# ---------------------------------------------------------
fig.add_trace(
    go.Scatter(
        x=x_axis,
        y=df_plot['z_score'],
        mode='lines',
        name='Z-Score',
        line=dict(color='#2ca02c', width=1.2),
        customdata=df_plot['time'],
        hovertemplate='<b>Time</b>: %{customdata|%Y-%m-%d %H:%M:%S}<br><b>Z-Score</b>: %{y:.2f}<extra></extra>'
    ),
    row=2, col=1
)

# Add Reference Threshold Lines to Bottom Panel
fig.add_hline(y=0.0, line=dict(color='black', width=1.2), row=2, col=1, annotation_text="Mean (Z=0)")
fig.add_hline(y=1.0, line=dict(color='orange', width=1, dash='dash'), row=2, col=1)
fig.add_hline(y=-1.0, line=dict(color='orange', width=1, dash='dash'), row=2, col=1)
fig.add_hline(y=2.0, line=dict(color='red', width=1.2, dash='dot'), row=2, col=1, annotation_text="High Dislocation (|Z|=2)")
fig.add_hline(y=-2.0, line=dict(color='red', width=1.2, dash='dot'), row=2, col=1)

# ---------------------------------------------------------
# LAYOUT & CUSTOM X-AXIS TICK FORMATTING (GAPLESS)
# ---------------------------------------------------------
num_ticks = 8
tick_positions = [int(x) for x in np.linspace(0, len(df_plot) - 1, num_ticks)]
tick_labels = df_plot['time'].iloc[tick_positions].dt.strftime('%H:%M:%S').tolist()

fig.update_layout(
    title_text="<b>Interactive Arbitrage Basis Spread & Z-Score Analysis</b>",
    template="plotly_white",
    height=800,
    hovermode='x unified',
    showlegend=False
)

fig.update_xaxes(
    tickvals=tick_positions,
    ticktext=tick_labels,
    title_text="Time (UTC)",
    row=2, col=1
)
fig.update_yaxes(title_text="Spread ($)", row=1, col=1)
fig.update_yaxes(title_text="Z-Score", row=2, col=1)

fig.show()

# Walk-forward testing
Separate target from features with very clear definition.

In [37]:
# =====================================================================
# 6. FULL PORTFOLIO BACKTEST (STATE MACHINE)
#    Simulates a running trading account. Tracks equity, handles positions,
#    applies latency to entries AND exits, and pays basis-point (bps) fees.
# =====================================================================
def run_full_backtest(
    df, 
    initial_capital=100000.0,
    trade_qty=1.0,           # Number of coins to trade per leg
    fee_bps=0.0005,          # 0.05% fee per leg (typical for crypto perp taker)
    entry_z=2.0,             # Z-score to enter trade
    exit_z=0.2,              # Z-score to exit trade (reversion to mean)
    stop_loss_z=6.0,         # Z-score to abort trade (regime breakdown)
    latency_ms=100           # Network latency to exchange
):
    timestamps = df['time'].values
    z = df['z_score'].values
    
    # Raw order book prices for crossing the spread
    perp_bid = df['perp_bid'].values
    perp_ask = df['perp_ask'].values
    spot_bid = df['spot_bid'].values
    spot_ask = df['spot_ask'].values
    n = len(df)
    
    # State tracking
    position = 0      # 0 = Flat, 1 = Short Perp/Long Spot, -1 = Long Perp/Short Spot
    cash = initial_capital
    equity_curve = [] # Logs (time, equity)
    trades = []       # Logs completed trades
    
    # Current trade variables
    entry_time = None
    entry_perp_price = 0.0
    entry_spot_price = 0.0
    
    i = 0
    while i < n:
        current_time = timestamps[i]
        current_z = z[i]
        
        # -------------------------------------------------
        # STATE 0: LOOKING FOR ENTRIES
        # -------------------------------------------------
        if position == 0:
            if abs(current_z) >= entry_z:
                # Determine direction
                direction = 1 if current_z >= entry_z else -1
                
                # Simulate latency: find the index 'latency_ms' in the future
                fill_time = current_time + np.timedelta64(latency_ms, 'ms')
                fill_idx = np.searchsorted(timestamps, fill_time)
                fill_idx = min(fill_idx, n - 1)
                
                # Execute Entry (Cross the spread)
                if direction == 1:
                    # Short Perp (hit bid), Long Spot (pay ask)
                    fill_perp = perp_bid[fill_idx]
                    fill_spot = spot_ask[fill_idx]
                else:
                    # Long Perp (pay ask), Short Spot (hit bid)
                    fill_perp = perp_ask[fill_idx]
                    fill_spot = spot_bid[fill_idx]
                
                # Calculate entry fees
                perp_fee = fill_perp * trade_qty * fee_bps
                spot_fee = fill_spot * trade_qty * fee_bps
                cash -= (perp_fee + spot_fee)
                
                # Update state
                position = direction
                entry_time = timestamps[fill_idx]
                entry_perp_price = fill_perp
                entry_spot_price = fill_spot
                
                # Jump index forward to the fill time
                i = fill_idx
                continue
                
        # -------------------------------------------------
        # STATE 1 / -1: IN A POSITION, LOOKING TO EXIT
        # -------------------------------------------------
        elif position != 0:
            # We exit if the spread reverts to the mean (exit_z) OR if it blows up (stop_loss_z)
            is_reverted = abs(current_z) <= exit_z
            is_stopped = abs(current_z) >= stop_loss_z
            is_end_of_data = (i == n - 1)
            
            if is_reverted or is_stopped or is_end_of_data:
                reason = "Reversion" if is_reverted else ("StopLoss" if is_stopped else "EndOfData")
                
                # Simulate latency for the exit
                fill_time = current_time + np.timedelta64(latency_ms, 'ms')
                fill_idx = np.searchsorted(timestamps, fill_time)
                fill_idx = min(fill_idx, n - 1)
                
                # Execute Exit (Cross the spread backwards)
                if position == 1:
                    # Buy back Perp (pay ask), Sell Spot (hit bid)
                    exit_perp = perp_ask[fill_idx]
                    exit_spot = spot_bid[fill_idx]
                    
                    perp_pnl = (entry_perp_price - exit_perp) * trade_qty
                    spot_pnl = (exit_spot - entry_spot_price) * trade_qty
                else:
                    # Sell back Perp (hit bid), Buy back Spot (pay ask)
                    exit_perp = perp_bid[fill_idx]
                    exit_spot = spot_ask[fill_idx]
                    
                    perp_pnl = (exit_perp - entry_perp_price) * trade_qty
                    spot_pnl = (entry_spot_price - exit_spot) * trade_qty
                    
                # Calculate exit fees
                perp_fee = exit_perp * trade_qty * fee_bps
                spot_fee = exit_spot * trade_qty * fee_bps
                total_fees = perp_fee + spot_fee
                
                gross_pnl = perp_pnl + spot_pnl
                net_pnl = gross_pnl - total_fees
                
                # Update Cash
                cash += net_pnl
                
                # Log Trade
                trades.append({
                    'entry_time': entry_time,
                    'exit_time': timestamps[fill_idx],
                    'position': position,
                    'holding_time_s': (timestamps[fill_idx] - entry_time) / np.timedelta64(1, 's'),
                    'gross_pnl': gross_pnl,
                    'fees': total_fees,
                    'net_pnl': net_pnl,
                    'exit_reason': reason
                })
                
                # Reset State
                position = 0
                i = fill_idx
                
        # Mark to market equity recording (sampled every step for the equity curve)
        # For a truly accurate MTM we should value the open positions, but for speed, 
        # we'll just record cash as equity while flat.
        if position == 0:
            equity_curve.append({'time': timestamps[i], 'equity': cash})
            
        i += 1
        
    df_trades = pd.DataFrame(trades)
    df_equity = pd.DataFrame(equity_curve)
    
    return df_trades, df_equity


# =====================================================================
# 7. PERFORMANCE METRICS GENERATOR
# =====================================================================
def generate_strategy_tearsheet(df_trades, df_equity, initial_capital):
    print("\n" + "="*70)
    print("=== FULL STRATEGY BACKTEST RESULTS ===")
    print("="*70)
    
    if df_trades.empty:
        print("No trades were executed with these parameters.")
        return
        
    total_trades = len(df_trades)
    winning_trades = len(df_trades[df_trades['net_pnl'] > 0])
    win_rate = winning_trades / total_trades
    
    total_net_profit = df_trades['net_pnl'].sum()
    total_fees_paid = df_trades['fees'].sum()
    final_equity = initial_capital + total_net_profit
    return_pct = (total_net_profit / initial_capital) * 100
    
    # Calculate Drawdown
    df_equity['high_water_mark'] = df_equity['equity'].cummax()
    df_equity['drawdown'] = (df_equity['equity'] - df_equity['high_water_mark']) / df_equity['high_water_mark']
    max_drawdown = df_equity['drawdown'].min() * 100
    
    print(f"Total Trades Executed:   {total_trades}")
    print(f"Win Rate:                {win_rate:.2%}")
    print(f"Total Net Profit:        ${total_net_profit:,.2f}")
    print(f"Total Fees Paid:         ${total_fees_paid:,.2f}")
    print(f"Final Account Balance:   ${final_equity:,.2f}")
    print(f"Total Return:            {return_pct:.2f}%")
    print(f"Maximum Drawdown:        {max_drawdown:.2f}%")
    
    print("\n--- Trade Exit Reasons ---")
    print(df_trades['exit_reason'].value_counts().to_string())
    
    print("\n--- Average Trade Stats ---")
    print(f"Avg Holding Time (sec):  {df_trades['holding_time_s'].mean():.2f}s")
    print(f"Avg Winner:              ${df_trades[df_trades['net_pnl'] > 0]['net_pnl'].mean():,.2f}")
    print(f"Avg Loser:               ${df_trades[df_trades['net_pnl'] <= 0]['net_pnl'].mean():,.2f}")


# =====================================================================
# 8. EXECUTION
# =====================================================================
if __name__ == "__main__":
    # 1. Run the data prep (You already have this)
    # df_signals = prepare_signals(df_arb, window=1000, max_staleness_ms=100, min_vol_usd=1.0)
    
    # 2. Run the Full Backtest
    # NOTE: Set trade_qty to a realistic coin amount for your capital!
    df_trades, df_equity = run_full_backtest(
        df=df_signals,
        initial_capital=100000.0,
        trade_qty=1.0,           # e.g., 1 BTC
        fee_bps=0,          # 0.05% per leg taker fee
        entry_z=2.0,             # Enter when z-score is 2.0
        exit_z=0.2,              # Exit when spread normalizes back to near 0
        stop_loss_z=6.0,         # Cut losses if z-score hits 6.0
        latency_ms=0           # 100ms lag from signal generation to exchange fill
    )
    
    # 3. Print the results
    generate_strategy_tearsheet(df_trades, df_equity, 100000.0)


=== FULL STRATEGY BACKTEST RESULTS ===
Total Trades Executed:   2583
Win Rate:                68.83%
Total Net Profit:        $9,211.00
Total Fees Paid:         $0.00
Final Account Balance:   $109,211.00
Total Return:            9.21%
Maximum Drawdown:        -3.82%

--- Trade Exit Reasons ---
exit_reason
StopLoss     2171
Reversion     412

--- Average Trade Stats ---
Avg Holding Time (sec):  9.79s
Avg Winner:              $14.67
Avg Loser:               $-20.96


# Conclusion
- In measuring ttr_ms median, regardless of the z-score between Q25 to Q50 it returned a consistent median of 19-20ms. Consider that the time of orders in the market should be naturally variable so this tells us that we hit a barrier where we have no visiblity into anything that happened faster than 20ms. The true measure of TTR could be 1ms-19ms. This could be an infrastructure limitation on our research. This is possibly caused by:
    - Inefficient code on our side: Our loops capturing websocket is buffering or it could be database bottleneck where timescaleDB is not loading websockets fast enough.
    - Bybit websocket hard limit: Bybit as a provider does not allow for websocket transmission below 20ms.
- Even with 0 latency and 0 fees, the strategy is not fully profitable and size of trade returns are skewed towards losses because of anomalous markets (breaking beyond z-score 6.0 for example). Another factor is when z-score from +-2 hits exit line, the profit captured might be smaller than bid ask spread.